# Catchment strategy comparison

This exploratory notebook uses the local Browney fixture to compare WBE pour-point strategies and catchment grouping rules. The EA polygon is treated as the output boundary; terrain is buffered beyond it so upstream flow paths have context.

The WBE terrain conditioning (depression filling, D8 pointer, and accumulation) is computed once and reused across strategies. Comparisons include stream thresholds and two snapping methods, then legacy grouping versus cumulative minimum-area grouping using the same raw WBE polygons.

The experiment checks the legacy assumption that polygon `VALUE - 1` corresponds to the input river-node order. If that identity does not hold, the notebook stops rather than silently mislabeling catchments.

In [1]:
from pathlib import Path
from tempfile import TemporaryDirectory

import geopandas as gpd
import matplotlib.pyplot as plt
import networkx as nx
import numpy as np
import polars as pl
import shapely
from shapely.geometry import Point
from whitebox_workflows import WbEnvironment
import elevatr

ROOT = Path.cwd()
BROWNEY = ROOT / "tests" / "fixtures" / "browney"
assert BROWNEY.exists(), "Run this notebook from the repository root."
TILE_CACHE = ROOT / "data" / "tiles"
MIN_AREA = 20_000.0
DEM_BUFFER_DEGREES = 0.15


## Load the EA boundary and build river-node pour points

The river fixtures are already clipped to the Browney catchment. The graph node ID is carried into the pour-point table. The notebook checks that generated nodes fall within the EA polygon and reports any exceptions.

In [2]:
import sys

sys.path.insert(0, str(ROOT / "src"))

from risk_map.config.models import DEFAULT_CONFIG
from risk_map.graph.network import build_river_graph
from risk_map.spatial.flow import LinearAccumulationFlowEstimator
from risk_map.spatial.grouping import merge_subcatchments_by_area
from risk_map.spatial.rivers import split_rivers

boundary_features = gpd.read_file(BROWNEY / "catchment.geojson")
boundary_features["geometry"] = boundary_features.geometry.make_valid()
boundary_features = boundary_features.to_crs(27700)
boundary_geometry = shapely.union_all(boundary_features.geometry.array)
boundary = gpd.GeoDataFrame(geometry=[boundary_geometry], crs=27700)

rivers = gpd.read_parquet(BROWNEY / "rivers.parquet").to_crs(27700)
estimator = LinearAccumulationFlowEstimator()
rivers["flow"] = estimator.estimate_flow(rivers).to_numpy()
speed = estimator.estimate_flow_speed(rivers)
rivers["flow_speed"] = speed if isinstance(speed, float) else speed.to_numpy()

rivers_split = split_rivers(rivers, resolution=DEFAULT_CONFIG.river_resolution)
river_graph = build_river_graph(rivers_split)

node_rows = [
    {"node_id": attributes["nodeID"], "geometry": Point(*node)}
    for node, attributes in river_graph.nodes(data=True)
]
nodes = gpd.GeoDataFrame(node_rows, geometry="geometry", crs=27700).sort_values("node_id")
inside = shapely.covers(boundary_geometry, nodes.geometry.array)
print(f"River nodes: {len(nodes):,}; outside EA boundary: {int((~inside).sum())}")
nodes.head()

River nodes: 426; outside EA boundary: 0


/home/crayboi/theme2C/.venv/lib/python3.13/site-packages/tqdm/auto.py:21: TqdmWarning: IProgress not found. Please update jupyter and ipywidgets. See https://ipywidgets.readthedocs.io/en/stable/user_install.html
  from .autonotebook import tqdm as notebook_tqdm


,node_id,geometry
0,0,POINT (425522.12 540928.38)
1,1,POINT (425775.757 540833.059)
2,2,POINT (425806.721 540569.975)
3,3,POINT (425607.988 540429.366)
4,4,POINT (425624.516 540223.062)


## Prepare WBE terrain once

The DEM bounds come from the EA boundary, expanded by a configurable geographic buffer. This is terrain context only; every polygon result is clipped back to the EA boundary. The buffer and DEM zoom are experiment parameters, not fixed scientific truths.

In [3]:
work = TemporaryDirectory(prefix="catchment_strategy_comparison_")
WORKSPACE = Path(work.name)
wbe = WbEnvironment()
wbe.verbose = False
wbe.working_directory = WORKSPACE.as_posix()
TILE_CACHE.mkdir(parents=True, exist_ok=True)

bounds = boundary.to_crs(4326).total_bounds.copy()
bounds += np.array([-DEM_BUFFER_DEGREES, -DEM_BUFFER_DEGREES, DEM_BUFFER_DEGREES, DEM_BUFFER_DEGREES])
elevation = elevatr.get_elev_raster(
    tuple(bounds), zoom=12, use_cache=True, delete_cache=False,
    crs="EPSG:4326", cache_folder=str(TILE_CACHE), verbose=False,
)
if elevation is None:
    raise RuntimeError("Elevation data could not be retrieved")
dem_path = WORKSPACE / "dem.tif"
elevation.to_tif(dem_path.as_posix())
dem = wbe.read_raster(dem_path.as_posix(), file_mode="m")
filled = wbe.hydrology.depressions_storage.fill_depressions(dem=dem)
d8_pointer = wbe.hydrology.flow_routing.d8_pointer(dem=filled)
flow_accumulation = wbe.hydrology.flow_routing.d8_flow_accum(
    input=d8_pointer, out_type="cells", clip=False, input_is_pointer=True
)
print("Terrain conditioning complete; the following strategies reuse this DEM and flow grid.")

CPLE_NotSupported in driver GTiff does not support creation option BOUNDS


Terrain conditioning complete; the following strategies reuse this DEM and flow grid.


## Run WBE strategy variants

`jenson` snaps to the nearest cell in a thresholded stream raster. `max_accumulation` snaps to the highest accumulation cell within the radius. Threshold variants change the extracted stream raster; accumulation snapping does not depend on that threshold. Each strategy receives the same terrain and same ordered node IDs.

In [4]:
def run_wbe_variant(stream_threshold: float, snap_method: str, snap_distance: float = 0.001):
    strategy_tag = f"{stream_threshold:g}_{snap_method}".replace(".", "_")
    point_path = WORKSPACE / f"pour_points_{strategy_tag}.shp"
    snapped_path = WORKSPACE / f"snapped_points_{strategy_tag}.shp"
    pour_points_gdf = nodes.to_crs(4326)[["node_id", "geometry"]].copy()
    pour_points_gdf["node_id"] = pour_points_gdf["node_id"].astype(str)
    pour_points_gdf.to_file(point_path.as_posix())

    if snap_method == "jenson":
        streams = wbe.streams.network_extraction.extract_streams(
            flow_accumulation=flow_accumulation, threshold=stream_threshold
        )
        snapped = wbe.hydrology.jenson_snap_pour_points(
            pour_pts=point_path.as_posix(),
            streams=streams,
            snap_dist=snap_distance,
            output=snapped_path.as_posix(),
        )
    elif snap_method == "max_accumulation":
        snapped = wbe.hydrology.watersheds_basins.snap_pour_points(
            pour_pts=point_path.as_posix(),
            flow_accum=flow_accumulation,
            snap_dist=snap_distance,
            output=snapped_path.as_posix(),
        )
    else:
        raise ValueError(f"Unknown snap method: {snap_method}")

    watershed = wbe.hydrology.watersheds_basins.watershed(
        d8_pntr=d8_pointer, pour_pts=snapped, esri_pntr=False
    )
    raster_path = WORKSPACE / f"watersheds_{strategy_tag}.tif"
    vector_path = WORKSPACE / f"catchments_{strategy_tag}.shp"
    wbe.write_raster(raster=watershed, output_path=raster_path.as_posix())
    polygons = wbe.conversion.raster_vector_conversion.raster_to_vector_polygons(
        input=raster_path.as_posix()
    )
    wbe.write_vector(vector=polygons, output_path=vector_path.as_posix())
    result = gpd.read_file(vector_path.as_posix()).to_crs(27700)
    result["geometry"] = result.geometry.make_valid()
    # This range check does not establish identity; feature-order labeling remains an assumption.
    node_ids = nodes["node_id"].to_list()
    values = result["VALUE"].astype(int)
    if values.min() < 1 or values.max() > len(node_ids):
        raise ValueError("WBE watershed VALUE labels do not match input point order")
    result["node_id"] = values.map(lambda value: node_ids[value - 1])
    return gpd.clip(result, boundary)

STRATEGIES = [
    {"name": "Jenson, threshold 500", "threshold": 500.0, "snap": "jenson"},
    {"name": "Jenson, threshold 1000 (legacy)", "threshold": 1000.0, "snap": "jenson"},
    {"name": "Jenson, threshold 2000", "threshold": 2000.0, "snap": "jenson"},
    {"name": "Max-accumulation snap", "threshold": 1000.0, "snap": "max_accumulation"},
]
wbe_results = {}
for strategy in STRATEGIES:
    print("Running", strategy["name"])
    wbe_results[strategy["name"]] = run_wbe_variant(
        strategy["threshold"], strategy["snap"]
    )
print("Completed strategies:", list(wbe_results))

Created 426 records


Running Jenson, threshold 500


/home/crayboi/theme2C/.venv/lib/python3.13/site-packages/pyogrio/raw.py:200: RuntimeWarning: /tmp/catchment_strategy_comparison_xm9oqy44/catchments_500_jenson.shp contains polygon(s) with rings with invalid winding order. Autocorrecting them, but that shapefile should be corrected using ogr2ogr for example.
  return ogr_read(
Created 426 records


Running Jenson, threshold 1000 (legacy)


/home/crayboi/theme2C/.venv/lib/python3.13/site-packages/pyogrio/raw.py:200: RuntimeWarning: /tmp/catchment_strategy_comparison_xm9oqy44/catchments_1000_jenson.shp contains polygon(s) with rings with invalid winding order. Autocorrecting them, but that shapefile should be corrected using ogr2ogr for example.
  return ogr_read(
Created 426 records


Running Jenson, threshold 2000


/home/crayboi/theme2C/.venv/lib/python3.13/site-packages/pyogrio/raw.py:200: RuntimeWarning: /tmp/catchment_strategy_comparison_xm9oqy44/catchments_2000_jenson.shp contains polygon(s) with rings with invalid winding order. Autocorrecting them, but that shapefile should be corrected using ogr2ogr for example.
  return ogr_read(
Created 426 records


Running Max-accumulation snap


/home/crayboi/theme2C/.venv/lib/python3.13/site-packages/pyogrio/raw.py:200: RuntimeWarning: /tmp/catchment_strategy_comparison_xm9oqy44/catchments_1000_max_accumulation.shp contains polygon(s) with rings with invalid winding order. Autocorrecting them, but that shapefile should be corrected using ogr2ogr for example.
  return ogr_read(


Completed strategies: ['Jenson, threshold 500', 'Jenson, threshold 1000 (legacy)', 'Jenson, threshold 2000', 'Max-accumulation snap']


## Compare raw WBE outputs

These maps show the raw watershed partition after clipping to the EA polygon. The table reports polygon count, total mapped area, minimum/median/maximum area, and how many river nodes received a polygon. These metrics help distinguish changes in stream extraction from changes in snapping.

In [5]:
import json

import plotly.graph_objects as go
from plotly.subplots import make_subplots


def plot_catchment_maps(panels):
    figure = make_subplots(
        rows=1,
        cols=len(panels),
        specs=[[{"type": "geo"} for _ in panels]],
        subplot_titles=[title for title, _, _ in panels],
        horizontal_spacing=0.02,
    )
    for column, (title, polygons, color_column) in enumerate(panels, start=1):
        features = polygons[[color_column, "geometry"]].copy()
        features["area"] = features.geometry.area
        features = features.explode(index_parts=False).reset_index(drop=True)
        features = features[features.geom_type.isin(["Polygon", "MultiPolygon"])]
        features = features.to_crs(4326).reset_index(drop=True)
        features["feature_id"] = features.index.astype(str)
        figure.add_trace(
            go.Choropleth(
                geojson=json.loads(features.to_json()),
                featureidkey="properties.feature_id",
                locations=features["feature_id"].to_list(),
                z=features[color_column].to_list(),
                customdata=features[["area"]].to_numpy(),
                colorscale="Viridis" if color_column == "area" else "Turbo",
                showscale=color_column == "area",
                colorbar={"title": "Area (m²)"},
                marker_line_width=0.25,
                marker_line_color="white",
                hovertemplate=(
                    f"{color_column}: %{{z}}<br>Area: %{{customdata[0]:,.0f}} m²<extra></extra>"
                ),
                name=title,
            ),
            row=1,
            col=column,
        )
        outline = boundary.to_crs(4326).geometry.boundary.explode(index_parts=False)
        for line in outline:
            longitude, latitude = line.xy
            figure.add_trace(
                go.Scattergeo(
                    lon=list(longitude), lat=list(latitude), mode="lines",
                    line={"color": "black", "width": 1},
                    showlegend=False, hoverinfo="skip",
                ),
                row=1,
                col=column,
            )
    figure.update_geos(fitbounds="locations", visible=False, projection_type="mercator")
    figure.update_layout(
        height=700, dragmode="pan", margin={"l": 10, "r": 10, "t": 60, "b": 10}
    )
    figure.show(
        renderer="plotly_mimetype",
        config={"scrollZoom": True, "displaylogo": False, "responsive": True},
    )
    return figure


raw_rows = []
for name, polygons in wbe_results.items():
    areas = polygons.geometry.area
    raw_rows.append({
        "strategy": name,
        "polygon_count": len(polygons),
        "node_count": polygons["node_id"].nunique(),
        "area_sum": float(areas.sum()),
        "area_min": float(areas.min()),
        "area_median": float(areas.median()),
        "area_max": float(areas.max()),
    })
raw_summary = pl.DataFrame(raw_rows).sort("strategy")
display(raw_summary)
raw_figure = plot_catchment_maps(
    [(name, polygons, "node_id") for name, polygons in wbe_results.items()]
)

strategy,polygon_count,node_count,area_sum,area_min,area_median,area_max
str,i64,i64,f64,f64,f64,f64
"""Jenson, threshold 1000 (legacy…",420,420,1.7751e8,128.654281,253818.237377,4.8199e6
"""Jenson, threshold 2000""",420,420,1.7751e8,128.654281,269372.557171,4.8199e6
"""Jenson, threshold 500""",420,420,1.7758e8,128.656109,243352.608122,4.8199e6
"""Max-accumulation snap""",420,420,1.7927e8,128.700272,253676.055915,4.8295e6


## Compare legacy grouping with cumulative-area grouping

This isolates the merge-policy difference using the same legacy WBE raw polygons and river graph. The legacy policy anchors groups based on each individual raw polygon's area; small polygons inherit the downstream node's group. The current policy adds upstream polygon areas until the group reaches `MIN_AREA`, and combines under-minimum branches at confluences.

In [6]:
def legacy_grouping(raw_polygons, graph, min_area):
    graph_ids = {
        attributes["nodeID"]
        for _, attributes in graph.nodes(data=True)
    }

    # WBE may omit nodes that were unsnapped or shared a snapped cell.
    # Keep those nodes in the graph with zero area and empty geometry.
    area_by_node = dict.fromkeys(graph_ids, 0.0)
    geometry_by_node = {
        node_id: shapely.Polygon() for node_id in graph_ids
    }
    area_by_node.update(
        dict(
            zip(
                raw_polygons["node_id"],
                raw_polygons.geometry.area,
                strict=True,
            )
        )
    )
    geometry_by_node.update(
        dict(
            zip(
                raw_polygons["node_id"],
                raw_polygons.geometry,
                strict=True,
            )
        )
    )

    group_by_node = {}
    outlets = [node for node in graph if graph.out_degree(node) == 0]
    frontier = []

    for outlet in outlets:
        outlet_id = graph.nodes[outlet]["nodeID"]
        group_by_node[outlet_id] = outlet_id
        frontier.append((outlet, outlet_id))

    while frontier:
        next_frontier = []

        for downstream_node, downstream_group in frontier:
            downstream_id = graph.nodes[downstream_node]["nodeID"]
            group_id = group_by_node[downstream_id]

            for upstream_node in graph.predecessors(downstream_node):
                upstream_id = graph.nodes[upstream_node]["nodeID"]

                if area_by_node[upstream_id] > min_area:
                    group_by_node[upstream_id] = upstream_id
                    next_frontier.append((upstream_node, upstream_id))
                else:
                    group_by_node[upstream_id] = group_id
                    next_frontier.append((upstream_node, group_id))

        frontier = next_frontier

    rows = []
    for group_id in dict.fromkeys(group_by_node.values()):
        members = [
            node_id
            for node_id, assigned_group in group_by_node.items()
            if assigned_group == group_id
        ]
        geometry = shapely.union_all(
            [geometry_by_node[node_id] for node_id in members]
        )
        rows.append(
            {
                "subcatchment_id": group_id,
                "node_ids": members,
                "area": geometry.area,
                "geometry": geometry,
            }
        )

    return gpd.GeoDataFrame(
        rows,
        geometry="geometry",
        crs=raw_polygons.crs,
    )


legacy_polygons = wbe_results["Jenson, threshold 1000 (legacy)"]
legacy_groups = legacy_grouping(
    legacy_polygons,
    river_graph,
    MIN_AREA,
)
cumulative_groups, node_mapping = merge_subcatchments_by_area(
    legacy_polygons,
    river_graph,
    min_area=MIN_AREA,
)

print(
    f"Legacy groups: {len(legacy_groups)}; "
    f"cumulative groups: {len(cumulative_groups)}"
)
display(
    pl.DataFrame(
        {
            "method": [
                "legacy per-polygon rule",
                "cumulative area rule",
            ],
            "group_count": [
                len(legacy_groups),
                len(cumulative_groups),
            ],
            "undersized_group_count": [
                int((legacy_groups["area"] < MIN_AREA).sum()),
                int(cumulative_groups["below_minimum"].sum()),
            ],
            "area_sum": [
                float(legacy_groups["area"].sum()),
                float(cumulative_groups["area"].sum()),
            ],
        }
    )
)
display(node_mapping.head())

Legacy groups: 357; cumulative groups: 359


method,group_count,undersized_group_count,area_sum
str,i64,i64,f64
"""legacy per-polygon rule""",357,0,1.7751e8
"""cumulative area rule""",359,0,1.7751e8


subcatchment_id,node_id,allocation_weight
i64,i64,f64
31,31,1.0
46,46,1.0
63,63,1.0
97,97,1.0
112,112,1.0


In [7]:
grouped_figure = plot_catchment_maps([
    ("Legacy: individual polygon threshold", legacy_groups, "subcatchment_id"),
    ("Cumulative area grouping", cumulative_groups, "subcatchment_id"),
    ("Legacy group area (m²)", legacy_groups, "area"),
])

cumulative_groups[["subcatchment_id", "area", "below_minimum"]].sort_values("area").head(20)

,subcatchment_id,area,below_minimum
36,48,21240.482605,False
340,3,22945.797737,False
224,222,23164.877920,False
260,106,24485.105126,False
50,49,28706.676812,False
106,130,34511.823734,False
148,189,35453.289036,False
322,24,36192.853001,False
358,21,36400.406821,False
131,267,37827.473548,False


## Interpretation checklist

- Do all strategies cover the EA boundary without gaps or overlaps?
- Which pour points fail to receive a polygon or share a snapped cell?
- Does changing stream threshold mostly affect headwaters, or shift catchment divides throughout the basin?
- Does max-accumulation snapping move points farther than Jenson stream snapping?
- How much does cumulative grouping reduce undersized polygons compared with the legacy per-polygon rule?
- Are merged polygon areas and node allocation weights consistent with load conservation?

The helper's current equal-node allocation is a v1 assumption. Compare it with reach-length weights if the results show that short terminal reaches receive disproportionate diffuse loads.